# 07 — Two follow-ups from the heard-space diagnosis

`06_heard_space_check_tim.ipynb` established that catalogue composition (small
vs medium vs genre-balanced) barely moved the external-seed comparison, and
that Pop's weak genre-agreement is intrinsic (high dispersion around its own
centroid), not a crowding artifact. Two follow-ups from that conversation:

1. **`genres_all`-based Familiar/Bridge/Adventurous tiers.** `genre_top` is a
   single lossy label; `track.genres_all` is FMA's full multi-label tagging
   (100% coverage on fma_small, 73% of tracks carry more than one tag,
   2.18 tags/track on average) and has been sitting unused. Bridge is defined
   the way it was described in conversation: audibly close but a genuinely
   different genre — not just "further down the rank list."
2. **An independent cross-check against EchoNest.** `echonest.csv` carries the
   *exact* feature family Spotify's own audio-features API is built on
   (Spotify acquired EchoNest in 2014 and kept the tech): acousticness,
   danceability, energy, instrumentalness, liveness, speechiness, tempo,
   valence. Only 1,294/8,000 fma-small tracks have it (16%), so it can't
   replace heard space, but for that slice it's a free, independent opinion —
   no API, no approximation.

In [1]:
import sys
sys.path.append("..")

import ast
from pathlib import Path
import numpy as np
import pandas as pd
from scipy.stats import pearsonr
from sklearn.preprocessing import StandardScaler

from modeling.data import load_fma, genre_labels
from modeling.features import space, scale_features, fit_pca, transform
from modeling.recommender import TrackRecommender, depth_for

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
pd.set_option("display.max_colwidth", 60)

In [2]:
X_heard = space("heard")
tracks = load_fma("small")[1].loc[X_heard.index]
Xs, scaler = scale_features(X_heard, method="standard")
pca = fit_pca(Xs, n_components=0.90)
rec = TrackRecommender(scaler, pca).fit(X_heard, tracks)
print(f"heard: {X_heard.shape[1]} columns -> {pca.n_components_} components, {len(tracks)} tracks")

heard: 154 columns -> 57 components, 7993 tracks


## 1. Familiar / Bridge / Adventurous, using `genres_all`

- **Familiar**: nearest neighbours whose `genres_all` overlaps the seed's.
- **Bridge**: neighbours within a generous audio-similarity window (top 150)
  whose `genres_all` does *not* overlap — audibly close, genuinely different
  genre. This is the operational version of "a nice link, like similar
  sampling" — here the link is the audio similarity itself.
- **Adventurous**: the existing `depth_for()` window (same geometric dial the
  recommender already uses), genre-agnostic.

In [3]:
genres_all = tracks[("track", "genres_all")].apply(ast.literal_eval)
genres_lookup = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "genres.csv", index_col=0)["title"]


def genre_names(ids):
    return [genres_lookup.get(i, str(i)) for i in ids]


def tiers_for(rec, seed_id=None, seed_vec=None, seed_genres=None, seed_artist=None,
              n_familiar=5, n_bridge=5, n_adventurous=5, bridge_window=150, adventure=0.85):
    # Familiar/Bridge/Adventurous for either a catalogue seed (seed_id) or an
    # external one (seed_vec, already transformed into rec's space;
    # seed_genres supplied explicitly since an external track has no genres_all)
    if seed_vec is None:
        row = rec._position(seed_id)
        seed_vec = rec.embedding_.iloc[[row]]
    distances, idx = rec.index_.kneighbors(seed_vec, n_neighbors=600)
    distances, idx = distances[0], idx[0]
    if seed_id is not None:
        distances, idx = distances[1:], idx[1:]  # drop the seed itself
    candidate_ids = rec.track_ids_[idx]

    if seed_artist is not None:
        artists = tracks.loc[candidate_ids, ("artist", "name")].to_numpy()
        keep = artists != seed_artist  # same exclusion recommend() already uses
        candidate_ids, distances = candidate_ids[keep], distances[keep]

    if seed_genres is None:
        seed_genres = set(genres_all.get(seed_id, []))
    overlaps = np.array([bool(seed_genres & set(genres_all.get(c, []))) for c in candidate_ids])

    familiar = [(candidate_ids[i], distances[i]) for i in range(len(candidate_ids)) if overlaps[i]][:n_familiar]
    bridge_pool = [(candidate_ids[i], distances[i])
                    for i in range(min(bridge_window, len(candidate_ids))) if not overlaps[i]]
    bridge = bridge_pool[:n_bridge]

    start = depth_for(adventure)
    adventurous = [(candidate_ids[i], distances[i])
                   for i in range(start, min(start + n_adventurous, len(candidate_ids)))]
    return familiar, bridge, adventurous


def show(label, items):
    print(f"  {label}:")
    for tid, d in items:
        meta = tracks.loc[tid]
        g = genre_names(genres_all.get(tid, []))
        print(f"    {d:.3f}  {meta[('artist','name')]} — {meta[('track','title')]}  "
              f"[{meta[('track','genre_top')]}] genres_all={g}")

In [4]:
# AWOL - Food (Hip-Hop, coherent); Albert Glasser - The Auction 2 (Instrumental,
# the strongest genre in notebook 06's sweep); Cryptacize - Say You Will (Pop,
# the incoherent one)
TIER_SEEDS = [2, 40659, 3538]

for seed_id in TIER_SEEDS:
    meta = tracks.loc[seed_id]
    print(f"\n=== SEED {seed_id}  {meta[('artist','name')]} — {meta[('track','title')]}  "
          f"[{meta[('track','genre_top')]}]  genres_all={genre_names(genres_all.get(seed_id, []))} ===")
    fam, bri, adv = tiers_for(rec, seed_id=seed_id, seed_artist=meta[("artist", "name")])
    show("Familiar", fam)
    show("Bridge", bri)
    show("Adventurous", adv)


=== SEED 2  AWOL — Food  [Hip-Hop]  genres_all=['Hip-Hop'] ===
  Familiar:
    0.315  Sun Sunych ft. DanBrown — Toys (ft. DanBrown)  [Hip-Hop] genres_all=['Rap', 'Hip-Hop']
    0.380  Gates — I Remember When  [Hip-Hop] genres_all=['Hip-Hop']
    0.382  SK — woke up feeling blessed  [Hip-Hop] genres_all=['Hip-Hop']
    0.387  SK — On the daily  [Hip-Hop] genres_all=['Hip-Hop']
    0.388  Cullah — Ninety Six  [Hip-Hop] genres_all=['Hip-Hop']
  Bridge:
    0.404  Decktonic — Future Music  [Electronic] genres_all=['Chip Music', 'Techno', 'House', 'Electronic']
    0.406  So Cow — Hrz  [Pop] genres_all=['Pop']
    0.428  YEIZON — YEIZON  [International] genres_all=['International']
    0.433  Barbarix — The Secret Garden  [Electronic] genres_all=['Ambient Electronic', 'Dubstep', 'Electronic']
    0.434  Teddy Brown — Crazy U  [International] genres_all=['Reggae - Dancehall', 'International', 'Reggae - Dub']
  Adventurous:
    0.557  Mike Morton — Avant le départ : Buka dikit jos  [Pop] gen

Worth flagging rather than glossing over: for the Pop seed, Bridge's
distances (0.285-0.327) are *closer* than Familiar's (0.341-0.413) — the
genuinely nearest-sounding tracks for this seed don't share its genre label at
all. That's not a bug in the tier logic; it's the same finding as notebook 06's
dispersion measurement showing up again, just from a different angle: Pop
doesn't have a large "familiar" zone to draw from in this catalogue, so the
tier split correctly reports that rather than papering over it. For the
Hip-Hop and Instrumental seeds the tiers separate cleanly and monotonically,
as expected for acoustically coherent genres.

**Listen:** all three seeds, all three tiers.

In [5]:
from modeling.rhythm import audio_path
import tempfile
import os
import librosa
import soundfile as sf
from IPython.display import Audio, display

PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    y, sr = librosa.load(path, sr=22050, mono=True)
    skip = min(10.0, 0.1 * len(y) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(y))
    start = max(0, end - int(seconds * sr))
    clip = y[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    # OGG/Vorbis, not raw Audio(clip, rate=sr): the uncompressed-WAV version
    # of this made notebooks 100MB+ and unrenderable in some editors.
    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

In [6]:
for seed_id in TIER_SEEDS:
    meta = tracks.loc[seed_id]
    print(f"\n=== SEED {seed_id}  {meta[('artist','name')]} — {meta[('track','title')]} ===")
    play(audio_path(seed_id), "SEED")
    fam, bri, adv = tiers_for(rec, seed_id=seed_id, seed_artist=meta[("artist", "name")])
    for label, items in [("Familiar", fam), ("Bridge", bri), ("Adventurous", adv)]:
        for tid, d in items:
            m = tracks.loc[tid]
            play(audio_path(tid), f"{label}  distance={d:.3f}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}]")


=== SEED 2  AWOL — Food ===
SEED


Familiar  distance=0.315  Sun Sunych ft. DanBrown — Toys (ft. DanBrown)  [Hip-Hop]


Familiar  distance=0.380  Gates — I Remember When  [Hip-Hop]


Familiar  distance=0.382  SK — woke up feeling blessed  [Hip-Hop]


Familiar  distance=0.387  SK — On the daily  [Hip-Hop]


...

Adventurous  distance=0.554  Quiet Hooves — Your Troubles + Feelin Down  [Pop]


Adventurous  distance=0.555  Yasna New York Bulgarian Women's Voices Choir — Malo Selo  [International]


Adventurous  distance=0.556  Squire Tuck — Sad Times  [Instrumental]


Adventurous  distance=0.556  David Szesztay — Surreal  [Instrumental]


Adventurous  distance=0.557  The Sounds of Taraab — Bashraf Salama  [International]


### The external seed: same tiers, no ground-truth genre to lean on

*Elyjah Slaps the Space* has no `genres_all` of its own — it never went
through FMA's tagging. Proxy: take its heard-space top-5 nearest catalogue
neighbours (computed the same way as notebook 06) and use the *union* of
their `genres_all` as a stand-in "inferred genre" for the Familiar/Bridge
split. Not ground truth, but a defensible consensus — and it's the same kind
of inference an unlabelled real-world seed would always need.

In [7]:
from modeling.external import extract_heard_features

SEED_PATH = REPO_ROOT / "data" / "raw" / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"
seed_row = extract_heard_features(SEED_PATH, X_heard.columns)
seed_embedding = transform(seed_row.to_frame().T, scaler, pca)

d0, idx0 = rec.index_.kneighbors(seed_embedding, n_neighbors=5)
neighbor_ids = rec.track_ids_[idx0[0]]
inferred_genres = set().union(*[set(genres_all.get(t, [])) for t in neighbor_ids])
print("inferred genre (union of top-5 neighbours' genres_all):", genre_names(inferred_genres))

ext_fam, ext_bri, ext_adv = tiers_for(rec, seed_vec=seed_embedding, seed_genres=inferred_genres)
print("\n=== SEED — Elyjah Slaps the Space (external, heard space) ===")
show("Familiar", ext_fam)
show("Bridge", ext_bri)
show("Adventurous", ext_adv)

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


inferred genre (union of top-5 neighbours' genres_all): ['Dance', 'Chip Music', 'Pop', 'Electronic', 'Chiptune', 'Soundtrack', 'Instrumental', 'Dubstep', 'House', 'Minimal Electronic', 'Trip-Hop']

=== SEED — Elyjah Slaps the Space (external, heard space) ===
  Familiar:
    0.333  Blue Dot Sessions — Scratcher  [Instrumental] genres_all=['Soundtrack', 'Instrumental']
    0.333  Les Filles et les Garçons — I Sing Despair  [Pop] genres_all=['Pop']
    0.334  Digi G'Alessio — Camuffarsi e Mantenere la Calma (Al Pianobar)  [Electronic] genres_all=['Dance', 'Dubstep', 'Trip-Hop', 'Electronic']
    0.353  Broke For Free — My Luck  [Electronic] genres_all=['Minimal Electronic', 'Electronic']
    0.361  UncleBibby — Chunky Worm Stew  [Electronic] genres_all=['Chiptune', 'Chip Music', 'House', 'Electronic']
  Bridge:
    0.434  Black Ant — Abstract Concepts - What up in the streets  [Hip-Hop] genres_all=['Hip-Hop']
    0.441  Tommy Tornado — Ruff Tuff  [International] genres_all=['Internationa

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


**Listen:** the seed, all three tiers.

In [8]:
play(SEED_PATH, "SEED — Elyjah Slaps the Space")
for label, items in [("Familiar", ext_fam), ("Bridge", ext_bri), ("Adventurous", ext_adv)]:
    for tid, d in items:
        m = tracks.loc[tid]
        play(audio_path(tid), f"{label}  distance={d:.3f}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}]")

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


SEED — Elyjah Slaps the Space


Familiar  distance=0.333  Blue Dot Sessions — Scratcher  [Instrumental]


Familiar  distance=0.333  Les Filles et les Garçons — I Sing Despair  [Pop]


Familiar  distance=0.334  Digi G'Alessio — Camuffarsi e Mantenere la Calma (Al Pianobar)  [Electronic]


...

Adventurous  distance=0.591  Blue Dot Sessions — Tossed  [Instrumental]


Adventurous  distance=0.591  Volfoniq — L'amour est enfant dub  [International]


Adventurous  distance=0.592  Los Margaritos — Dios anda pedo  [Rock]


Adventurous  distance=0.592  cultureculture — Baby Blue  [Pop]


Adventurous  distance=0.592  Cheese N Pot-C — Tabiji Shiyo  [Hip-Hop]


## 2. Cross-check against EchoNest

Same feature family Spotify's own `audio-features` endpoint exposes, computed
independently of anything in this project. Sample random track pairs from the
1,294-track overlap, compute both heard-space cosine distance and EchoNest
Euclidean distance (features standardized) for each pair, and correlate.

In [9]:
Z = pd.DataFrame(pca.transform(scaler.transform(X_heard)), index=X_heard.index)
Zu = Z.to_numpy() / np.linalg.norm(Z.to_numpy(), axis=1, keepdims=True)

echonest = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "echonest.csv", index_col=0, header=[0, 1, 2])
en = echonest["echonest"]["audio_features"]
en = en.loc[en.index.intersection(tracks.index)].dropna()
print(f"echonest x fma_small overlap: {len(en)} tracks")

En = StandardScaler().fit_transform(en)
en_index = en.index
pos_in_Z = {tid: i for i, tid in enumerate(Z.index)}
pos_in_En = {tid: i for i, tid in enumerate(en_index)}

rng = np.random.default_rng(3)
sample_ids = rng.choice(en_index, size=min(400, len(en_index)), replace=False)
pairs_rng = np.random.default_rng(5)
pair_a = pairs_rng.choice(sample_ids, size=3000)
pair_b = pairs_rng.choice(sample_ids, size=3000)

heard_d = []
per_feat_d = {c: [] for c in en.columns}
for a, b in zip(pair_a, pair_b):
    if a == b:
        continue
    ia, ib = pos_in_Z[a], pos_in_Z[b]
    heard_d.append(1 - Zu[ia] @ Zu[ib])
    ja, jb = pos_in_En[a], pos_in_En[b]
    for c in en.columns:
        per_feat_d[c].append(abs(en[c].iloc[ja] - en[c].iloc[jb]))

heard_d = np.array(heard_d)
en_d = np.array([np.linalg.norm(En[pos_in_En[a]] - En[pos_in_En[b]])
                  for a, b in zip(pair_a, pair_b) if a != b])
r_overall, p_overall = pearsonr(heard_d, en_d)
print(f"overall correlation (heard-space distance vs EchoNest-space distance): "
      f"r={r_overall:.3f}  p={p_overall:.2g}  n_pairs={len(heard_d)}")

echonest x fma_small overlap: 1294 tracks


overall correlation (heard-space distance vs EchoNest-space distance): r=0.256  p=4.5e-46  n_pairs=2993


In [10]:
print("broken down by individual EchoNest dimension:")
for c in en.columns:
    r, p = pearsonr(heard_d, np.array(per_feat_d[c]))
    print(f"  {c:20s} r={r:+.3f}  p={p:.2g}")

broken down by individual EchoNest dimension:
  acousticness         r=+0.316  p=1.7e-70
  danceability         r=+0.199  p=3.7e-28
  energy               r=+0.218  p=1.8e-33
  instrumentalness     r=+0.094  p=2.8e-07
  liveness             r=-0.010  p=0.59
  speechiness          r=+0.077  p=2.3e-05
  tempo                r=+0.059  p=0.0013
  valence              r=+0.065  p=0.00034


Weak-but-real overall agreement (r≈0.26, p≈1e-45 — far from noise, far from
strong). Broken down: heard space tracks EchoNest's **acousticness** and
**energy**/**danceability** reasonably (all timbre/rhythm-adjacent — makes
sense given what heard space actually measures), and is close to blind to
**valence** (mood), **liveness**, and **tempo perception**. Worth remembering
next time "why doesn't this feel familiar" comes up: valence is plausibly
closer to what a listener means by that than raw timbre is, and it's the
dimension this feature space captures worst.